
<div style="text-align: center; line-height: 0; padding-top: 9px;">
  <img
    src="https://databricks.com/wp-content/uploads/2018/03/db-academy-rgb-1200px.png"
    alt="Databricks Learning"
  >
</div>


# Lab - Monitoring Drift with Data Profiling

In this lab, you will investigate how to detect drift. You will work through a series of practical exercises to simulate prediction drift, set up data profiling for inference tables, and analyze drift metrics. The lab also includes hands-on tasks to explore visual dashboards, extract and modify SQL code, and create custom alerts. Additionally, you will learn to inspect lineage, enabling you to trace the flow of data and associated dashboards and queries.


**Learning Objectives**
By the end of this lab, you will have completed the following:
- Initiate Data Profiling programmatically
- Inspect automatically generated Dashboard
- Create a new widget in the data profiling dashboard
- Inspect Profile and Drift Metrics tables
- Setup an Alert

## REQUIRED - SELECT CLASSIC COMPUTE
Before executing cells in this notebook, please select your classic compute cluster in the lab. Be aware that **Serverless** is enabled by default.
Follow these steps to select the classic compute cluster:
1. Navigate to the top-right of this notebook and click the drop-down menu to select your cluster. By default, the notebook will use **Serverless**.
1. If your cluster is available, select it and continue to the next cell. If the cluster is not shown:
   - In the drop-down, select **More**.
   - In the **Attach to an existing compute resource** pop-up, select the first drop-down. You will see a unique cluster name in that drop-down. Please select that cluster.

**NOTE:** If your cluster has terminated, you might need to restart it in order to select it. To do this:
1. Right-click on **Compute** in the left navigation pane and select *Open in new tab*.
1. Find the triangle icon to the right of your compute cluster name and click it.
1. Wait a few minutes for the cluster to start.
1. Once the cluster is running, complete the steps above to select your cluster.


## Requirements

Please review the following requirements before starting the lesson:

* To run this notebook, you need to use one of the following Databricks runtime(s): **17.3.x-cpu-ml-scala2.13**

* To utilize the generated Dashboard, you will need a SQL Warehouse.

## Classroom Setup

To get into the lesson, we first need to build some data assets and define some configuration variables required for this lab. When running the following cell, the output is hidden so our space isn't cluttered. To view the details of the output, you can hover over the next cell and click the eye icon. 

The cell after the setup, titled `View Setup Variables`, displays the various variables that were created. You can click the Catalog icon in the notebook space to the right to see that your catalog was created with no data.

In [0]:
%run ../Includes/Classroom-Setup-4.Lab

  Using cached databricks_sdk-0.122.0-py3-none-any.whl.metadata (44 kB)
  Using cached protobuf-6.33.6-cp39-abi3-manylinux2014_x86_64.whl.metadata (593 bytes)
Using cached databricks_sdk-0.122.0-py3-none-any.whl (969 kB)
Using cached protobuf-6.33.6-cp39-abi3-manylinux2014_x86_64.whl (323 kB)
  Attempting uninstall: protobuf
    Found existing installation: protobuf 5.29.4
    Not uninstalling protobuf at /databricks/python3/lib/python3.12/site-packages, outside environment /local_disk0/.ephemeral_nfs/envs/pythonEnv-d342bd31-4e8e-47ea-8a21-9b46e654efe6
    Can't uninstall 'protobuf'. No files were found to uninstall.
  Attempting uninstall: databricks-sdk
    Found existing installation: databricks-sdk 0.49.0
    Not uninstalling databricks-sdk at /databricks/python3/lib/python3.12/site-packages, outside environment /local_disk0/.ephemeral_nfs/envs/pythonEnv-d342bd31-4e8e-47ea-8a21-9b46e654efe6
    Can't uninstall 'databricks-sdk'. No files were found to uninstall.
ERROR: pip's depende

Inference table created successfully.
Model logs table created successfully.


## Initiate Inference Data Profiling

Here you will use Python to initiate the data profiling of your inference table using Data Profiling. This will generate two table: profile metrics and drift metrics. In addition, a Databricks Dashboard will also be generated. We will inspect all these assets later. 

Terminology: 
- Your **primary table** is your inference table you created by running the classroom setup. The name of this table is `model_logs`.
- Your **baseline table** is your source of truth for your data. The name of this table is `baseline_features`

In [0]:
from databricks.sdk import WorkspaceClient
from databricks.sdk.service.catalog import MonitorInferenceLog, MonitorInferenceLogProblemType, MonitorInfoStatus, MonitorRefreshInfoState, MonitorMetric
w = WorkspaceClient()
# full_primary_table_name = <FILL_IN>
# full_baseline_table_name = <FILL_IN>
full_primary_table_name = f'{DA.catalog_name}.{DA.schema_name}.model_logs'
full_baseline_table_name = f"{DA.catalog_name}.{DA.schema_name}.baseline_features"


<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Set the primary (model_logs) and baseline table names
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
from databricks.sdk import WorkspaceClient
from databricks.sdk.service.catalog import MonitorInferenceLog, MonitorInferenceLogProblemType, MonitorInfoStatus, MonitorRefreshInfoState, MonitorMetric
w = WorkspaceClient()
full_primary_table_name = f'{DA.catalog_name}.{DA.schema_name}.model_logs'
full_baseline_table_name = f"{DA.catalog_name}.{DA.schema_name}.baseline_features"
```

</div>
</details>

During the initial classroom setup, we registered our inference table with Unity Catalog that contained features, predictions, and labels for a classification problem. Next, we will set essential variables that will be used for enabling Data Profiling and initiating data profiling. 

Configure the setup with the following conditions. 
1. Set the window size to **1 day**
1. Store the generated notebook in a folder in your homeworkspace with the path `<username>/My_Monitored_Dashboards/Drift_Detection`
1. Set the slicer to include `Ages` between 3 and 10 and `HvyAlcoholConsump` to be 1 (non-alcoholic).

In [0]:
## ML problem type, either "classification" or "regression"
PROBLEM_TYPE = MonitorInferenceLogProblemType.<FILL_IN>

## Window sizes to analyze data over
GRANULARITIES = <FILL_IN>   

## Directory to store generated dashboard
ASSETS_DIR = f"/Workspace/Users/{DA.username}/databricks_lakehouse_monitoring/{primary_table_name}"

## Optional parameters
SLICING_EXPRS = <FILL_IN>   # Expressions to slice data with

In [0]:
## ML problem type, either "classification" or "regression"
PROBLEM_TYPE = MonitorInferenceLogProblemType.PROBLEM_TYPE_CLASSIFICATION

## Window sizes to analyze data over
GRANULARITIES = ["1 day"]   

## Directory to store generated dashboard
ASSETS_DIR = f"/Workspace/Users/{DA.username}/My_Monitored_Dashboards/Drift_Detection"

## Optional parameters
SLICING_EXPRS = ["Age < 10", "Age > 3", "HvyAlcoholConsump = 1"]   # Expressions to slice data with



<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Configure profiling: problem type, granularity, dashboard path, and slices
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
## ML problem type, either "classification" or "regression"
PROBLEM_TYPE = MonitorInferenceLogProblemType.PROBLEM_TYPE_CLASSIFICATION

## Window sizes to analyze data over
GRANULARITIES = ["1 day"]   

## Directory to store generated dashboard
ASSETS_DIR = f"/Workspace/Users/{DA.username}/My_Monitored_Dashboards/Drift_Detection"

## Optional parameters
SLICING_EXPRS = ["Age < 10", "Age > 3", "HvyAlcoholConsump = 1"]   # Expressions to slice data with
```

</div>
</details>

Run the initialization for Data Profiling using the configuration above. Recall that for this dataset, we are interested in `Diabetes_binary` as our target variable.

In [0]:
print(f"Creating monitor for model_logs")
try: 
  info = w.quality_monitors.create(
    table_name=<FILL_IN>,
    inference_log=MonitorInferenceLog(
      timestamp_col='timestamp',
      granularities=<FILL_IN>,
      model_id_col='model_id',  ## Model version number 
      prediction_col=<FILL_IN>,  ## Ensure this column is of type DOUBLE
      problem_type=<FILL_IN>,
      label_col=<FILL_IN>  ## Ensure this column is of type DOUBLE
    ),
    baseline_table_name=<FILL_IN>,
    slicing_exprs=<FILL_IN>,
    output_schema_name=f"{DA.catalog_name}.{DA.schema_name}",
    assets_dir=<FILL_IN>
  )

  import time

  ## Wait for monitor to be created
  while info.status ==  MonitorInfoStatus.MONITOR_STATUS_PENDING:
    info = w.quality_monitors.get(table_name=<FILL_IN>)
    time.sleep(10)

  assert info.status == MonitorInfoStatus.MONITOR_STATUS_ACTIVE, "Error creating monitor"
except Exception as e:
  print(f"Error creating monitor: {e}")

In [0]:
print(f"Creating monitor for model_logs")
try: 
  info = w.quality_monitors.create(
    table_name=full_primary_table_name,
    inference_log=MonitorInferenceLog(
      timestamp_col='timestamp',
      granularities=GRANULARITIES,
      model_id_col='model_id',  ## Model version number 
      prediction_col='Diabetes_binary',  ## Ensure this column is of type DOUBLE
      problem_type=PROBLEM_TYPE,
      label_col='labeled_data'  ## Ensure this column is of type DOUBLE
    ),
    baseline_table_name=full_baseline_table_name,
    slicing_exprs=SLICING_EXPRS,
    output_schema_name=f"{DA.catalog_name}.{DA.schema_name}",
    assets_dir=ASSETS_DIR
  )

  import time

  ## Wait for monitor to be created
  while info.status ==  MonitorInfoStatus.MONITOR_STATUS_PENDING:
    info = w.quality_monitors.get(table_name=full_primary_table_name)
    time.sleep(10)

  assert info.status == MonitorInfoStatus.MONITOR_STATUS_ACTIVE, "Error creating monitor"
except Exception as e:
  print(f"Error creating monitor: {e}")


Creating monitor for model_logs



<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Create the inference-log quality monitor
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
print(f"Creating monitor for model_logs")
try: 
  info = w.quality_monitors.create(
    table_name=full_primary_table_name,
    inference_log=MonitorInferenceLog(
      timestamp_col='timestamp',
      granularities=GRANULARITIES,
      model_id_col='model_id',  ## Model version number 
      prediction_col='Diabetes_binary',  ## Ensure this column is of type DOUBLE
      problem_type=PROBLEM_TYPE,
      label_col='labeled_data'  ## Ensure this column is of type DOUBLE
    ),
    baseline_table_name=full_baseline_table_name,
    slicing_exprs=SLICING_EXPRS,
    output_schema_name=f"{DA.catalog_name}.{DA.schema_name}",
    assets_dir=ASSETS_DIR
  )

  import time

  ## Wait for monitor to be created
  while info.status ==  MonitorInfoStatus.MONITOR_STATUS_PENDING:
    info = w.quality_monitors.get(table_name=full_primary_table_name)
    time.sleep(10)

  assert info.status == MonitorInfoStatus.MONITOR_STATUS_ACTIVE, "Error creating monitor"
except Exception as e:
  print(f"Error creating monitor: {e}")
```

</div>
</details>

In [0]:
## A metric refresh will automatically be triggered on creation
refreshes = w.quality_monitors.list_refreshes(table_name=<FILL_IN>).refreshes
assert(len(refreshes) > 0)

run_info = refreshes[0]
while run_info.state in (MonitorRefreshInfoState.PENDING, MonitorRefreshInfoState.RUNNING):
  run_info = w.quality_monitors.get_refresh(table_name=<FILL_IN>, refresh_id=run_info.refresh_id)
  print(run_info)
  time.sleep(30)

assert run_info.state == MonitorRefreshInfoState.SUCCESS, "Monitor refresh failed"

In [0]:
## A metric refresh will automatically be triggered on creation
refreshes = w.quality_monitors.list_refreshes(table_name=full_primary_table_name).refreshes
assert(len(refreshes) > 0)

run_info = refreshes[0]
while run_info.state in (MonitorRefreshInfoState.PENDING, MonitorRefreshInfoState.RUNNING):
  run_info = w.quality_monitors.get_refresh(table_name=full_primary_table_name, refresh_id=run_info.refresh_id)
  print(run_info)
  time.sleep(30)

assert run_info.state == MonitorRefreshInfoState.SUCCESS, "Monitor refresh failed"


MonitorRefreshInfo(refresh_id=396511545489468, state=<MonitorRefreshInfoState.RUNNING: 'RUNNING'>, start_time_ms=1793310605225, end_time_ms=None, message=None, trigger=<MonitorRefreshInfoTrigger.MANUAL: 'MANUAL'>)
MonitorRefreshInfo(refresh_id=396511545489468, state=<MonitorRefreshInfoState.RUNNING: 'RUNNING'>, start_time_ms=1793310605225, end_time_ms=None, message=None, trigger=<MonitorRefreshInfoTrigger.MANUAL: 'MANUAL'>)
MonitorRefreshInfo(refresh_id=396511545489468, state=<MonitorRefreshInfoState.RUNNING: 'RUNNING'>, start_time_ms=1793310605225, end_time_ms=None, message=None, trigger=<MonitorRefreshInfoTrigger.MANUAL: 'MANUAL'>)
MonitorRefreshInfo(refresh_id=396511545489468, state=<MonitorRefreshInfoState.RUNNING: 'RUNNING'>, start_time_ms=1793310605225, end_time_ms=None, message=None, trigger=<MonitorRefreshInfoTrigger.MANUAL: 'MANUAL'>)
MonitorRefreshInfo(refresh_id=396511545489468, state=<MonitorRefreshInfoState.RUNNING: 'RUNNING'>, start_time_ms=1793310605225, end_time_ms=None


<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Wait for the initial monitor refresh to complete
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
## A metric refresh will automatically be triggered on creation
refreshes = w.quality_monitors.list_refreshes(table_name=full_primary_table_name).refreshes
assert(len(refreshes) > 0)

run_info = refreshes[0]
while run_info.state in (MonitorRefreshInfoState.PENDING, MonitorRefreshInfoState.RUNNING):
  run_info = w.quality_monitors.get_refresh(table_name=full_primary_table_name, refresh_id=run_info.refresh_id)
  print(run_info)
  time.sleep(30)

assert run_info.state == MonitorRefreshInfoState.SUCCESS, "Monitor refresh failed"
```

</div>
</details>

## Locate the Data Profiling Dashboard

There are two methods for locating the Data Profiling Dashboard.

1. Navigate to the underlying inference table `model_logs` and click on **Quality** and click on **View Dashboard**
1. Navigate to the underlying inference table `model_logs` and click on **Lineage** and click on **Open in a dashboard** and find the dashboard you just created.

### Inspect Data Profiling Dashboard

1. After navigating to the canvas, scroll down until you see **Numerical Feature Drift**.
1. Click on the kebab on the widget with title **# Features with Numerical Drift**.
1. Click on **View Dataset**. This will take you to the generated **SQL code**. Modify it to not limit to the latest window by commenting out a single line.
1. Copy and paste your answer in the next cell.

**Do not run the SQL code** -  you will receive an error since you are working in a notebook. However, you can run the modified code in the Data tab of your dashboard.

In [0]:
## Copy and paste the code you modified above. 
# <FILL_IN>
%sql
WITH 
profile_metrics AS (
  SELECT * FROM `dbacademy`.<`schema-name`>.`model_logs_profile_metrics`
  WHERE window.start >= :`Time Window Start` AND window.end <= :`Time Window End` -- limit to the inspection time window range
  AND isnull(slice_key) AND isnull(slice_value) -- default to "No Slice"
  AND   `model_id`   = "*" -- default to all model ids
),
last_window_in_inspection_range AS (
  SELECT window.start AS Window, granularity AS Granularity FROM profile_metrics
  WHERE window.start IN (SELECT MAX(window.start) FROM profile_metrics) 
  ORDER BY Granularity LIMIT 1 -- order to ensure the `granularity` selected is stable
),
profile_metrics_inspected AS (
  SELECT * FROM profile_metrics
  WHERE Granularity = (SELECT Granularity FROM last_window_in_inspection_range)
)
SELECT
  concat(window.start," - ", window.end) AS Window,
  CONCAT('"', ELEMENT_AT(frequent_items, 1).item, '", ', CAST((ELEMENT_AT(frequent_items, 1).count / count) * 100 AS INT), "%") AS top_class,
  granularity AS Granularity,
    `model_id`   AS `Model Id`,
  COALESCE(slice_key, "No slice") AS `Slice key`,
  COALESCE(slice_value, "No slice") AS `Slice value`
FROM profile_metrics_inspected
WHERE
  -- window.start IN (SELECT Window FROM last_window_in_inspection_range) -- limit to last window
  log_type = "INPUT"
  AND column_name = "Diabetes_binary"


  File <command-8418504087727738>, line 5
    profile_metrics AS (
                    ^
SyntaxError: invalid syntax



<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> SQL to inspect the profile metrics table
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
%sql
WITH 
profile_metrics AS (
  SELECT * FROM `dbacademy`.<`schema-name`>.`model_logs_profile_metrics`
  WHERE window.start >= :`Time Window Start` AND window.end <= :`Time Window End` -- limit to the inspection time window range
  AND isnull(slice_key) AND isnull(slice_value) -- default to "No Slice"
  AND   `model_id`   = "*" -- default to all model ids
),
last_window_in_inspection_range AS (
  SELECT window.start AS Window, granularity AS Granularity FROM profile_metrics
  WHERE window.start IN (SELECT MAX(window.start) FROM profile_metrics) 
  ORDER BY Granularity LIMIT 1 -- order to ensure the `granularity` selected is stable
),
profile_metrics_inspected AS (
  SELECT * FROM profile_metrics
  WHERE Granularity = (SELECT Granularity FROM last_window_in_inspection_range)
)
SELECT
  concat(window.start," - ", window.end) AS Window,
  CONCAT('"', ELEMENT_AT(frequent_items, 1).item, '", ', CAST((ELEMENT_AT(frequent_items, 1).count / count) * 100 AS INT), "%") AS top_class,
  granularity AS Granularity,
    `model_id`   AS `Model Id`,
  COALESCE(slice_key, "No slice") AS `Slice key`,
  COALESCE(slice_value, "No slice") AS `Slice value`
FROM profile_metrics_inspected
WHERE
  -- window.start IN (SELECT Window FROM last_window_in_inspection_range) -- limit to last window
  log_type = "INPUT"
  AND column_name = "Diabetes_binary"
```

</div>
</details>

> **⚠️ Note:**  
> You may encounter a `CAST_INVALID_INPUT` error in the **Numerical Feature Quantile Drift** widget.  
> This occurs because the auto-generated query attempts to cast the string `"Baseline"` to a `TIMESTAMP` type in the `Window` column.  
> While this error does not affect other metrics or drift detection functionality, you can optionally resolve it using the steps below.

**Steps to Diagnose and Fix the Error (Optional)**
- **Step 1:**  
  Navigate to the **Numerical Feature Quantile Drift** widget in the data profiling dashboard.  
  If there's a rendering failure, you will see a `CAST_INVALID_INPUT` error message displayed within the widget.
- **Step 2:**  
  Click the **kebab menu (⋮)** in the top-right corner of the widget and select **View Dataset**.  
  This opens the SQL query that powers the visual.
- **Step 3:**  
  In the dataset editor, scroll down and click **Diagnose error**.  
  The Genie Code will analyze the issue and provide a suggested fix.
- **Step 4:**  
  Click **Replace active cell content** to apply the Genie's suggested query.  
  The corrected query will ensure the `Window` column in the baseline portion uses a proper timestamp type, typically by replacing `"Baseline"` with `CAST(NULL AS TIMESTAMP)`.
- **Step 5:**  
  Click **Run** to execute the updated query.
- **Step 6:**  
  Once the query runs successfully, the widget should render correctly, and the error message will disappear.
This fix helps ensure type consistency in the `UNION` clause across datasets, resolving the rendering error in the visual.

### Create a New Widget in the Canvas

Next, create a new widget that provides a visual counter for the precision macro during the last window. 

Steps: 
1. Navigate to the canvas you just created. 
1. Copy or create a new visualization using the **Add a visualization** blue button at the bottom of the Canvas screen. 
1. Set the Dataset value to **performance_last_window**. 
1. Set the **Visualization** to **Counter**.
1. Set the **Value** to **precision_macro**. 
1. Set the **Comparison** to **Window**.
1. Give it a title **Precision Macro** as the **Title** and **In the last time window** for the **Description**.

## Inspect Profile and Drift Metrics 

Now we will turn our focus to inspecting the profile and drift metric tables that were created when we set up Data Profiling. Let's read in both tables.

In [0]:
## Display drift metrics table
drift_table = f"{DA.catalog_name}.{DA.schema_name}.<FILL_IN>"
drift_table_df = spark.sql(<FILL_IN>)
display(drift_table_df.orderBy(F.rand()))

## Display profile metrics table
profile_table = f"{DA.catalog_name}.{DA.schema_name}.<FILL_IN>"
profile_table_df = spark.sql(<FILL_IN>)
display(drift_table_df.orderBy(F.rand()))

In [0]:
## Display drift metrics table
drift_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_drift_metrics"
drift_table_df = spark.sql(f"SELECT * FROM {drift_table}")
display(drift_table_df.orderBy(F.rand()))

## Display profile metrics table
profile_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_profile_metrics"
profile_table_df = spark.sql(f"SELECT * FROM {profile_table}")
display(profile_table_df.orderBy(F.rand()))


window,granularity,monitor_version,model_id,slice_key,slice_value,column_name,data_type,window_cmp,drift_type,count_delta,avg_delta,percent_null_delta,percent_zeros_delta,percent_distinct_delta,non_null_columns_delta,js_distance,ks_test,wasserstein_distance,population_stability_index,chi_squared_test,tv_distance,l_infinity_distance
"List(2026-10-29T14:00:00Z, 2026-10-29T15:00:00Z)",1 hour,0,0,null,null,CholCheck,double,null,BASELINE,-70691,0.024741130538109002,0.0,-2.474113053810898,99.9971708255531,null,null,"List(0.0245, 1.0)",0.0245,0.6274906864629062,null,null,null
"List(2026-10-28T00:00:00Z, 2026-10-29T00:00:00Z)",1 day,0,*,null,null,:table,null,"List(2026-10-27T00:00:00Z, 2026-10-28T00:00:00Z)",CONSECUTIVE,13,null,null,null,null,"List(0, 0)",null,null,null,null,null,null,null
"List(2026-10-07T01:00:00Z, 2026-10-07T02:00:00Z)",1 hour,0,0,null,null,BMI,double,null,BASELINE,-70691,-17.854807892080643,0.0,0.0,0.9251400441351194,null,null,"List(0.9995, 9.999999999998899E-4)",17.852830640465253,8.279369020827833,null,null,null
"List(2026-10-05T05:00:00Z, 2026-10-05T06:00:00Z)",1 hour,0,0,null,null,Smoker,double,null,BASELINE,-70691,0.5247269846658744,0.0,-52.47269846658745,99.9971708255531,null,null,"List(0.5245, 0.9510000000000001)",0.5245,5.754160515741273,null,null,null
"List(2026-10-01T14:00:00Z, 2026-10-01T15:00:00Z)",1 hour,0,0,null,null,PhysActivity,double,null,BASELINE,-70691,0.4383098511854241,0.0,-43.83098511854241,99.9971708255531,null,null,"List(0.4385, 1.0)",0.4385,4.669131585113577,null,null,null
"List(2026-10-03T02:00:00Z, 2026-10-03T03:00:00Z)",1 hour,0,0,null,null,databricks_request_id,string,"List(2026-10-03T01:00:00Z, 2026-10-03T02:00:00Z)",CONSECUTIVE,0,null,0.0,null,0.0,null,0.8325546111576977,null,null,null,"List(0.0, 1.0)",1.0,1.0
"List(2026-10-24T06:00:00Z, 2026-10-24T07:00:00Z)",1 hour,0,*,null,null,HvyAlcoholConsump,double,"List(2026-10-24T05:00:00Z, 2026-10-24T06:00:00Z)",CONSECUTIVE,0,0.0,0.0,0.0,0.0,null,null,"List(0.0, NaN)",0.0,1.1499112716961868,null,null,null
"List(2026-10-10T14:00:00Z, 2026-10-10T15:00:00Z)",1 hour,0,0,null,null,Fruits,double,"List(2026-10-10T13:00:00Z, 2026-10-10T14:00:00Z)",CONSECUTIVE,0,-1.0,0.0,100.0,0.0,null,null,"List(1.0, NaN)",1.0,16.098773119050072,null,null,null
"List(2026-10-09T04:00:00Z, 2026-10-09T05:00:00Z)",1 hour,0,0,null,null,Age,double,"List(2026-10-09T03:00:00Z, 2026-10-09T04:00:00Z)",CONSECUTIVE,0,2.0,0.0,0.0,0.0,null,null,"List(1.0, NaN)",2.0,16.09877311905007,null,null,null
"List(2026-10-06T22:00:00Z, 2026-10-06T23:00:00Z)",1 hour,0,0,null,null,PhysActivity,double,null,BASELINE,-70691,-0.5616901488145759,0.0,56.16901488145759,99.9971708255531,null,null,"List(0.5615, 0.877)",0.5615,5.754160515741276,null,null,null


window log_type logging_table_commit_version monitor_version granularity slice_key slice_value model_id column_name count data_type num_nulls avg quantiles min max stddev num_zeros num_nan min_length max_length avg_length non_null_columns frequent_items accuracy_score log_loss roc_auc_score confusion_matrix acceptance_rate median distinct_count percent_nan percent_null percent_zeros percent_distinct precision recall f1_score false_positive_rate statistical_parity equal_opportunity predictive_equality predictive_parity List(2026-10-20T19:00:00Z, 2026-10-20T20:00:00Z) INPUT 1 0 1 hour null null 0 date 1 date 0 null null null null null null null null null null null null null null null null null null 1 null 0.0 null 100.0 null null null null null null null null List(2026-10-20T22:00:00Z, 2026-10-20T23:00:00Z) INPUT 1 0 1 hour null null 0 BMI 1 double 0 33.0 List(33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.0, 33.


<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Display the drift and profile metrics tables
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
## Display drift metrics table
drift_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_drift_metrics"
drift_table_df = spark.sql(f"SELECT * FROM {drift_table}")
display(drift_table_df.orderBy(F.rand()))

## Display profile metrics table
profile_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_profile_metrics"
profile_table_df = spark.sql(f"SELECT * FROM {profile_table}")
display(profile_table_df.orderBy(F.rand()))
```

</div>
</details>

### Use SQL to Analyze Profile Metrics Table

Next, display the profile metrics table where the baseline data was logged and the f1-score is not null and order by accuracy_score.

In [0]:
## Display profile metrics table
profile_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_profile_metrics"
profile_table_df = spark.sql(f"SELECT * FROM {profile_table} where f1_score is not null and log_type = 'BASELINE' order by accuracy_score")
display(profile_table_df.orderBy(F.rand()))

window,log_type,logging_table_commit_version,monitor_version,granularity,slice_key,slice_value,model_id,column_name,count,data_type,num_nulls,avg,quantiles,min,max,stddev,num_zeros,num_nan,min_length,max_length,avg_length,non_null_columns,frequent_items,accuracy_score,log_loss,roc_auc_score,confusion_matrix,acceptance_rate,median,distinct_count,percent_nan,percent_null,percent_zeros,percent_distinct,precision,recall,f1_score,false_positive_rate,statistical_parity,equal_opportunity,predictive_equality,predictive_parity
null,BASELINE,0,0,null,null,null,0,:table,70692,null,null,null,null,null,null,null,null,null,null,null,null,"List(Diabetes_binary, HighBP, HighChol, CholCheck, BMI, Smoker, Stroke, HeartDiseaseorAttack, PhysActivity, Fruits, Veggies, HvyAlcoholConsump, AnyHealthcare, NoDocbcCost, GenHlth, MentHlth, PhysHlth, DiffWalk, Sex, Age, Education, Income, id, labeled_data)",null,0.49878345498783455,null,null,"List(List(0.0, 0.0, 20081), List(1.0, 0.0, 19881), List(0.0, 1.0, 15551), List(1.0, 1.0, 15179))","Map(0.0 -> 0.5040457194590618, 1.0 -> 0.49595428054093815)",null,null,null,null,null,null,"List(Map(0.0 -> 0.563566457117198, 1.0 -> 0.4329435253850542), 0.4982549912511261, 0.5067843220505882)","List(Map(0.0 -> 0.5025023772583955, 1.0 -> 0.49394728278555156), 0.49822483002197354, 0.49878345498783455)","List(Map(0.0 -> 0.5312855517633674, 1.0 -> 0.46143790849673205), 0.49636173013004975, 0.500922595876086)","List(Map(0.0 -> 0.5060527172144484, 1.0 -> 0.49749762274160453), 0.5017751699780265, 0.5023337949438874)",null,null,null,null


### Use SQL to inspect the drift metrics

Use SQL to inspect drift metrics by finding all records where
1. The drift type is baseline
1. No slice key
1. BMI data only

In [0]:
%sql
-- <FILL_IN>
select * from model_logs_drift_metrics
where drift_type = 'BASELINE' AND slice_key is null and column_name = 'BMI'


window,granularity,monitor_version,model_id,slice_key,slice_value,column_name,data_type,window_cmp,drift_type,count_delta,avg_delta,percent_null_delta,percent_zeros_delta,percent_distinct_delta,non_null_columns_delta,js_distance,ks_test,wasserstein_distance,population_stability_index,chi_squared_test,tv_distance,l_infinity_distance
"List(2026-10-13T00:00:00Z, 2026-10-14T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70680,-11.104807892080643,0.0,0.0,-7.408193289198223,null,null,"List(0.635, 3.177347099818287E-5)",11.104768301360426,4.952938636102607,null,null,null
"List(2026-09-29T00:00:00Z, 2026-09-30T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70690,-10.854807892080643,0.0,0.0,0.9251400441351194,null,null,"List(0.8675, 0.03511249999999998)",10.859830640465251,6.805587364168895,null,null,null
"List(2026-10-24T00:00:00Z, 2026-10-25T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70682,-13.954807892080645,0.0,0.0,-29.07485995586488,null,null,"List(0.869, 2.9772135640963858E-9)",13.959768301360429,7.484256097370393,null,null,null
"List(2026-10-29T00:00:00Z, 2026-10-30T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70679,-18.16250019977295,0.0,0.0,-52.92101380201873,null,null,"List(0.9445, 9.480664459469112E-17)",18.162268301360427,11.38130799436462,null,null,null
"List(2026-10-10T00:00:00Z, 2026-10-11T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70678,-15.354807892080643,0.0,0.0,-27.64628852729345,null,null,"List(0.841, 1.3619916406932894E-11)",15.353768301360429,7.623459005940964,null,null,null
"List(2026-10-23T00:00:00Z, 2026-10-24T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70681,-14.945716982989733,0.0,0.0,-8.165769046773974,null,null,"List(0.893, 4.209706190619274E-11)",14.948268301360427,8.585113387057287,null,null,null
"List(2026-10-20T00:00:00Z, 2026-10-21T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70675,-15.972454950904172,0.0,0.0,-40.25133054410017,null,null,"List(0.91, 3.3354609862191303E-18)",15.971268301360428,8.074467557815135,null,null,null
"List(2026-10-21T00:00:00Z, 2026-10-22T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70681,-16.49117152844428,0.0,0.0,-26.347587228592147,null,null,"List(0.9685, 6.059629725444554E-17)",16.489268301360426,9.080605545858676,null,null,null
"List(2026-10-01T00:00:00Z, 2026-10-02T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70682,-15.654807892080644,0.0,0.0,-9.07485995586488,null,null,"List(0.8145, 1.0046462800509233E-7)",15.657768301360427,9.322923856544747,null,null,null
"List(2026-10-04T00:00:00Z, 2026-10-05T00:00:00Z)",1 day,0,0,null,null,BMI,double,null,BASELINE,-70682,-14.954807892080645,0.0,0.0,-19.07485995586488,null,null,"List(0.9115, 5.894713508915948E-11)",14.956268301360428,8.659439772070433,null,null,null



<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Inspect drift metrics (baseline, no slice, BMI only)
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```sql
%sql
select * from model_logs_drift_metrics
where drift_type = 'BASELINE' AND slice_key is null and column_name = 'BMI'
```

</div>
</details>

Build custom code to inspect drift using KS test.

In [0]:
import pandas as pd
import json

## Load the drift metrics data from the UC managed table
drift_table =<FILL_IN>
drift_metrics_df = <FILL_IN>

## Convert to Pandas DataFrame
data = drift_metrics_df.toPandas()

## Convert Timestamp objects to strings in 'window' and 'window_cmp'
def convert_timestamp_to_string(d):
    if isinstance(d, dict):
        for k, v in d.items():
            if isinstance(v, pd.Timestamp):
                d[k] = v.isoformat()
            elif isinstance(v, dict):
                d[k] = convert_timestamp_to_string(v)
    return d

data['window'] = data['window'].apply(<FILL_IN>)
data['window_cmp'] = data['window_cmp'].apply(<FILL_IN>)

## Ensure JSON fields are strings
data['window'] = data['window'].apply(json.dumps)
data['window_cmp'] = data['window_cmp'].apply(json.dumps)

## Convert the JSON string in 'window' and 'window_cmp' to dictionaries
for index, row in data.iterrows():
    row['window'] = json.loads(row['window'])
    row['window_cmp'] = json.loads(row['window_cmp'])

## Analyze the drift metrics setting the threshold to 0.6
drift_thresholds = <FILL_IN>




def check_drift(row):
    ks_test_value = row['ks_test'].get('statistic') if isinstance(row['ks_test'], dict) else row['ks_test']
    if ks_test_value is not None and ks_test_value > drift_thresholds['ks_test']:
        return True
    return False

data['drift_detected'] = data.apply(<FILL_IN>, axis=1)

## Display rows with drift detected
drifted_rows = <FILL_IN>
no_drifted_rows = <FILL_IN>

print("Rows with drift detected:")
display(drifted_rows)

print("\nRows with no drift detected:")
display(no_drifted_rows)

In [0]:
import pandas as pd
import json

## Load the drift metrics data from the UC managed table
drift_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_drift_metrics"
drift_metrics_df = spark.read.table(drift_table)

## Convert to Pandas DataFrame
data = drift_metrics_df.toPandas()

## Convert Timestamp objects to strings in 'window' and 'window_cmp'
def convert_timestamp_to_string(d):
    if isinstance(d, dict):
        for k, v in d.items():
            if isinstance(v, pd.Timestamp):
                d[k] = v.isoformat()
            elif isinstance(v, dict):
                d[k] = convert_timestamp_to_string(v)
    return d

data['window'] = data['window'].apply(convert_timestamp_to_string)
data['window_cmp'] = data['window_cmp'].apply(convert_timestamp_to_string)

## Ensure JSON fields are strings
data['window'] = data['window'].apply(json.dumps)
data['window_cmp'] = data['window_cmp'].apply(json.dumps)

## Convert the JSON string in 'window' and 'window_cmp' to dictionaries
for index, row in data.iterrows():
    row['window'] = json.loads(row['window'])
    row['window_cmp'] = json.loads(row['window_cmp'])

## Analyze the drift metrics
drift_thresholds = {
    "ks_test": 0.6,
}

def check_drift(row):
    ks_test_value = row['ks_test'].get('statistic') if isinstance(row['ks_test'], dict) else row['ks_test']
    if ks_test_value is not None and ks_test_value > drift_thresholds['ks_test']:
        return True
    return False

data['drift_detected'] = data.apply(check_drift, axis=1)

## Display rows with drift detected
drifted_rows = data[data['drift_detected']]
no_drifted_rows = data[~data['drift_detected']]

print("Rows with drift detected:")
display(drifted_rows)

print("\nRows with no drift detected:")
display(no_drifted_rows)


Rows with drift detected:


window,granularity,monitor_version,model_id,slice_key,slice_value,column_name,data_type,window_cmp,drift_type,count_delta,avg_delta,percent_null_delta,percent_zeros_delta,percent_distinct_delta,non_null_columns_delta,js_distance,ks_test,wasserstein_distance,population_stability_index,chi_squared_test,tv_distance,l_infinity_distance,drift_detected
"{""start"": ""2026-10-13T00:00:00"", ""end"": ""2026-10-14T00:00:00""}",1 day,0,0,null,null,BMI,double,null,BASELINE,-70680,-11.104807892080643,0.0,0.0,-7.408193289198223,null,null,"List(3.177347099818287E-5, 0.635)",11.104768301360426,4.952938636102607,null,null,null,true
"{""start"": ""2026-09-29T00:00:00"", ""end"": ""2026-09-30T00:00:00""}",1 day,0,0,null,null,BMI,double,null,BASELINE,-70690,-10.854807892080643,0.0,0.0,0.9251400441351194,null,null,"List(0.03511249999999998, 0.8675)",10.859830640465251,6.805587364168895,null,null,null,true
"{""start"": ""2026-10-05T00:00:00"", ""end"": ""2026-10-06T00:00:00""}",1 day,0,0,null,null,Age,double,null,BASELINE,-70678,2.3513970229311045,0.0,0.0,-71.42857142857143,null,null,"List(4.46999606177735E-6, 0.6385)",2.707430784796898,5.004503650703122,null,null,null,true
"{""start"": ""2026-10-16T00:00:00"", ""end"": ""2026-10-17T00:00:00""}",1 day,0,0,null,null,Income,double,null,BASELINE,-70687,1.959107112544559,0.0,0.0,99.99434165110621,null,null,"List(6.480401006247502E-4, 0.7995)",2.1425,13.454537178385035,null,null,null,true
"{""start"": ""2026-10-24T00:00:00"", ""end"": ""2026-10-25T00:00:00""}",1 day,0,0,null,null,BMI,double,null,BASELINE,-70682,-13.954807892080645,0.0,0.0,-29.07485995586488,null,null,"List(2.9772135640963858E-9, 0.869)",13.959768301360429,7.484256097370393,null,null,null,true
"{""start"": ""2026-10-29T00:00:00"", ""end"": ""2026-10-30T00:00:00""}",1 day,0,0,null,null,BMI,double,null,BASELINE,-70679,-18.16250019977295,0.0,0.0,-52.92101380201873,null,null,"List(9.480664459469112E-17, 0.9445)",18.162268301360427,11.38130799436462,null,null,null,true
"{""start"": ""2026-10-10T00:00:00"", ""end"": ""2026-10-11T00:00:00""}",1 day,0,0,null,null,Age,double,null,BASELINE,-70678,2.2799684515025334,0.0,0.0,-71.42857142857143,null,null,"List(4.46999606177735E-6, 0.6385)",2.635430784796898,4.9676950463742084,null,null,null,true
"{""start"": ""2026-10-18T00:00:00"", ""end"": ""2026-10-19T00:00:00""}",1 day,0,0,null,null,Age,double,null,BASELINE,-70683,2.4228255943596757,0.0,0.0,-55.55555555555556,null,null,"List(4.287073185394227E-4, 0.6385)",2.7051471139431946,4.849169154472789,null,null,null,true
"{""start"": ""2026-10-24T00:00:00"", ""end"": ""2026-10-25T00:00:00""}",1 day,0,0,null,null,Age,double,null,BASELINE,-70682,2.4228255943596757,0.0,0.0,-60.0,null,null,"List(1.719949684706152E-4, 0.6385)",2.6685284517113708,4.920411014675426,null,null,null,true
"{""start"": ""2026-09-29T00:00:00"", ""end"": ""2026-09-30T00:00:00""}",1 day,0,0,null,null,Income,double,null,BASELINE,-70690,-1.1408928874554407,0.0,0.0,99.99434165110621,null,null,"List(0.0748845, 0.8065)",1.244,8.279369020827833,null,null,null,true



Rows with no drift detected:


window,granularity,monitor_version,model_id,slice_key,slice_value,column_name,data_type,window_cmp,drift_type,count_delta,avg_delta,percent_null_delta,percent_zeros_delta,percent_distinct_delta,non_null_columns_delta,js_distance,ks_test,wasserstein_distance,population_stability_index,chi_squared_test,tv_distance,l_infinity_distance,drift_detected
"{""start"": ""2026-10-07T00:00:00"", ""end"": ""2026-10-08T00:00:00""}",1 day,0,0,null,null,HighBP,double,null,BASELINE,-70682,0.43654161715611384,0.0,-43.65416171561138,9.997170825553104,null,null,"List(0.02993360130383449, 0.4365)",0.4365,4.669131585113577,null,null,null,false
"{""start"": ""2026-10-27T00:00:00"", ""end"": ""2026-10-28T00:00:00""}",1 day,0,0,null,null,HighBP,double,null,BASELINE,-70687,0.23654161715611388,0.0,-23.65416171561138,39.997170825553106,null,null,"List(0.8851891118080001, 0.236)",0.236,4.561317182149544,null,null,null,false
"{""start"": ""2026-10-08T00:00:00"", ""end"": ""2026-10-09T00:00:00""}",1 day,0,0,null,null,HighBP,double,null,BASELINE,-70689,0.10320828382278047,0.0,-10.320828382278052,66.66383749221976,null,null,"List(1.0, 0.103)",0.10299999999999998,4.4810710876137145,null,null,null,false
"{""start"": ""2026-10-29T00:00:00"", ""end"": ""2026-10-30T00:00:00""}",1 day,0,0,null,null,HighChol,double,null,BASELINE,-70679,0.08968156553456164,0.0,-8.968156553456161,15.381786210168489,null,null,"List(0.9995352633592877, 0.09)",0.08999999999999997,4.448449700638812,null,null,null,false
"{""start"": ""2026-09-29T00:00:00"", ""end"": ""2026-09-30T00:00:00""}",1 day,0,0,null,null,HighChol,double,null,BASELINE,-70690,-0.5257030498500538,0.0,52.57030498500537,49.997170825553106,null,null,"List(0.45030050000000005, 0.5255)",0.5255000000000001,5.754160515741276,null,null,null,false
"{""start"": ""2026-10-11T00:00:00"", ""end"": ""2026-10-12T00:00:00""}",1 day,0,0,null,null,CholCheck,double,null,BASELINE,-70685,0.024741130538109002,0.0,-2.474113053810898,14.282885111267388,null,null,"List(1.0, 0.0245)",0.0245,0.6274906864629062,null,null,null,false
"{""start"": ""2026-10-26T00:00:00"", ""end"": ""2026-10-27T00:00:00""}",1 day,0,0,null,null,Smoker,double,null,BASELINE,-70682,0.12472698466587445,0.0,-12.472698466587453,19.997170825553102,null,null,"List(0.9924794185600485, 0.124)",0.12399999999999994,5.459009718058175,null,null,null,false
"{""start"": ""2026-10-20T00:00:00"", ""end"": ""2026-10-21T00:00:00""}",1 day,0,0,null,null,Stroke,double,null,BASELINE,-70675,-0.0033475790587835924,0.0,0.3347579058783481,11.761876707906044,null,null,"List(1.0, 0.004)",0.0040000000000000036,8.501813120256589,null,null,null,false
"{""start"": ""2026-10-21T00:00:00"", ""end"": ""2026-10-22T00:00:00""}",1 day,0,0,null,null,Stroke,double,null,BASELINE,-70681,0.11964707334763353,0.0,-11.964707334763347,18.178989007371285,null,null,"List(0.9922823300364682, 0.119)",0.119,9.076198863790491,null,null,null,false
"{""start"": ""2026-10-18T00:00:00"", ""end"": ""2026-10-19T00:00:00""}",1 day,0,0,null,null,HeartDiseaseorAttack,double,null,BASELINE,-70683,0.03669439257624624,0.0,-3.6694392576246315,22.219393047775323,null,null,"List(1.0, 0.037)",0.03700000000000003,7.26308284503771,null,null,null,false



<details style="margin: 8px 0;">
<summary style="background: linear-gradient(135deg, #1B5162, #2574B5); color: white; padding: 14px 20px; cursor: pointer; font-weight: 700; font-size: 13pt; border-radius: 8px; user-select: none; display: flex; align-items: center; gap: 10px;">
<span style="background: rgba(255,255,255,0.2); border-radius: 4px; padding: 2px 8px; font-size: 11pt;">ANSWER</span> Load and flatten the drift metrics into a Pandas DataFrame
</summary>
<div style="border: 2px solid #1B5162; border-top: none; border-radius: 0 0 8px 8px; padding: 18px 20px; background: #F8F9FC; position: relative;"><button onclick="var c=this.parentElement.querySelector('pre code');var t=document.createElement('textarea');t.value=c?c.textContent:'';t.style.position='fixed';t.style.opacity='0';document.body.appendChild(t);t.select();document.execCommand('copy');document.body.removeChild(t);this.textContent='Copied!';var b=this;setTimeout(function(){b.textContent='Copy'},1500)" style="position:absolute;top:10px;right:12px;background:linear-gradient(135deg,#1B5162,#2574B5);color:#fff;border:none;border-radius:6px;padding:6px 14px;font-size:11pt;font-weight:600;cursor:pointer;z-index:2;">Copy</button>

```python
import pandas as pd
import json

## Load the drift metrics data from the UC managed table
drift_table = f"{DA.catalog_name}.{DA.schema_name}.model_logs_drift_metrics"
drift_metrics_df = spark.read.table(drift_table)

## Convert to Pandas DataFrame
data = drift_metrics_df.toPandas()

## Convert Timestamp objects to strings in 'window' and 'window_cmp'
def convert_timestamp_to_string(d):
    if isinstance(d, dict):
        for k, v in d.items():
            if isinstance(v, pd.Timestamp):
                d[k] = v.isoformat()
            elif isinstance(v, dict):
                d[k] = convert_timestamp_to_string(v)
    return d

data['window'] = data['window'].apply(convert_timestamp_to_string)
data['window_cmp'] = data['window_cmp'].apply(convert_timestamp_to_string)

## Ensure JSON fields are strings
data['window'] = data['window'].apply(json.dumps)
data['window_cmp'] = data['window_cmp'].apply(json.dumps)

## Convert the JSON string in 'window' and 'window_cmp' to dictionaries
for index, row in data.iterrows():
    row['window'] = json.loads(row['window'])
    row['window_cmp'] = json.loads(row['window_cmp'])

## Analyze the drift metrics
drift_thresholds = {
    "ks_test": 0.6,
}

def check_drift(row):
    ks_test_value = row['ks_test'].get('statistic') if isinstance(row['ks_test'], dict) else row['ks_test']
    if ks_test_value is not None and ks_test_value > drift_thresholds['ks_test']:
        return True
    return False

data['drift_detected'] = data.apply(check_drift, axis=1)

## Display rows with drift detected
drifted_rows = data[data['drift_detected']]
no_drifted_rows = data[~data['drift_detected']]

print("Rows with drift detected:")
display(drifted_rows)

print("\nRows with no drift detected:")
display(no_drifted_rows)
```

</div>
</details>


## Lineage and Alerts for Drift Detection

The following instructions are not meant to send you an alert to any device. It is only to demonstrate how to use lineage alongside alerts for your metric tables.

1. **Navigate to Queries**:
   - On the left-hand sidebar of the Databricks workspace, click on **Queries**.

1. **Create a Query**:
   - Click on **Create Query** in the top-right corner.
   - Write a query to calculate the average value of the **Count** column in your profile metrics table:

      ```SELECT AVG(Count) AS avg_count FROM model_logs_profile_metrics;```

   - Give the Query a name like `Drift Alert 1`
   > ****Note:**** Before running the query, make sure to set the current catalog and schema, and follow the `catalog.schema.table_name` structure.
   - Once the query is complete, click **Save** to save it.

1. **Create an Alert**:
   - Navigate to **Alerts** on the left-hand sidebar and click **Create Alert**.
   - Provide the alert with a **name** like `Test alert`.
   - In the SQL editor panel, paste the query you have saved before.
> ****Note:**** Before running the query, make sure to set the current catalog and schema, and follow the `catalog.schema.table_name` structure.
   - Click the **Run all** button to validate the query.
   - Define a **Trigger Condition**:
     - Example: Trigger the alert when the value is above 20.
   - Click **Test condition**.
     - If the result satisfies the condition, you’ll see:`Triggered: Alert will trigger based on current data.`
   - Under **Notify**, search and add users or destinations. 
   - Finally, click **View alert** and Set the **Schedule**.
1. **Monitor Lineage and Updates**:
   - Go back to the **Catalog** on the left sidebar.
   - Navigate to your **model_logs_profile_metrics** table.
   - Click on **Lineage** and then see the queries associated with this table.
      - You will see the `Drift Alert 1` listed there.
   - Whenever there’s an update or drift detected in your model or dataset, the alert will notify you automatically. You can then go to the table's **Lineage** tab to investigate the issue.

## Conclusion

In this lab, you learned how to programmatically setup Data Profiling on an inference table for detecting drift. This included investigating the automatically generated dashboard as well as the two metric tables: profile metrics and drift metrics. Additionally, you set up an alert use SQL to notify you when you suspect drifting may occur.

&copy; 2026 Databricks, Inc. All rights reserved. Apache, Apache Spark, Spark, the Spark Logo, Apache Iceberg, Iceberg, and the Apache Iceberg logo are trademarks of the <a href="https://www.apache.org/" target="_blank">Apache Software Foundation</a>.<br/><br/><a href="https://databricks.com/privacy-policy" target="_blank">Privacy Policy</a> | <a href="https://databricks.com/terms-of-use" target="_blank">Terms of Use</a> | <a href="https://help.databricks.com/" target="_blank">Support</a>